In [1]:
import os, json, shutil
from pathlib import Path
import numpy as np
import nibabel as nib
import matplotlib.pyplot as plt
from matplotlib.colors import ListedColormap, BoundaryNorm
from tqdm import tqdm
from glob import glob
import pandas as pd
import torch
import nnunetv2 as _nnunetv2_pkg

EPOCHS     = 250
BATCH_SIZE = 5
PATCH_SIZE = 128

# Fontes RAW oficiais
TRAIN_RAW = Path("/home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-With-GroundTruth")
VAL_RAW   = Path("/home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-ValidationData")

# Base isolada do modelo final
NNUNET_BASE = Path("/home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub")
NNUNET_RAW = NNUNET_BASE / "nnUNet_raw"
NNUNET_PREP = NNUNET_BASE / "nnUNet_preprocessed"
NNUNET_RES = NNUNET_BASE / "nnUNet_results"
for p in [NNUNET_RAW, NNUNET_PREP, NNUNET_RES]:
    p.mkdir(parents=True, exist_ok=True)

os.environ["nnUNet_raw"] = str(NNUNET_RAW)
os.environ["nnUNet_preprocessed"] = str(NNUNET_PREP)
os.environ["nnUNet_results"] = str(NNUNET_RES)

DATASET_ID = 999
DATASET_NAME = "BraTS-GoAT-modified-sub"
DATASET_FOLDER = NNUNET_RAW / f"Dataset{DATASET_ID:03d}_{DATASET_NAME}"
imagesTr = DATASET_FOLDER / "imagesTr"
labelsTr = DATASET_FOLDER / "labelsTr"
imagesVs = DATASET_FOLDER / "imagesVs"
for p in [imagesTr, labelsTr, imagesVs]:
    p.mkdir(parents=True, exist_ok=True)

# Configuracao ResEnc + Modified trainer
PLANNER    = "nnUNetPlannerResEncL"
PLANS_NAME = "nnUNetResEncUNetLPlans"
TRAINER    = "nnUNetTrainer_250epochs_Modified"
CONFIG     = "3d_fullres"
FOLDS      = [0, 1, 2, 3, 4]

# Predicoes isoladas (val oficial) - last (checkpoint_final) e best (checkpoint_best)
PRED_LAST = Path("/home/henrique.grande/brats_goat_experiments/predictions/nnUnet_modified_sub_last")
PRED_BEST = Path("/home/henrique.grande/brats_goat_experiments/predictions/nnUnet_modified_sub_best")
for root in [PRED_LAST, PRED_BEST]:
    (root / "ofc_validation_raw").mkdir(parents=True, exist_ok=True)
    (root / "ofc_validation").mkdir(parents=True, exist_ok=True)

DATASET_FOLDER

PosixPath('/home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_raw/Dataset999_BraTS-GoAT-modified-sub')

In [2]:
print("=" * 60)
print("  Informacoes da GPU")
print("=" * 60)
if torch.cuda.is_available():
    props = torch.cuda.get_device_properties(0)
    print("  CUDA   :", torch.version.cuda, "| PyTorch:", torch.__version__)
    print("  GPU    :", props.name)
    print("  VRAM   :", f"{props.total_memory/1e9:.2f} GB")
else:
    print("  CUDA   : NAO")
print("=" * 60)

  Informacoes da GPU
  CUDA   : 12.1 | PyTorch: 2.5.1+cu121
  GPU    : NVIDIA H100 80GB HBM3
  VRAM   : 85.02 GB


In [3]:
def get_patient_ids(directory: Path) -> list:
    if not directory.exists():
        return []
    return sorted([d.name for d in directory.iterdir() if d.is_dir()])

train_ids = get_patient_ids(TRAIN_RAW)
val_ids = get_patient_ids(VAL_RAW)

print(f"Treino (With-GroundTruth): {len(train_ids)} casos | existe: {TRAIN_RAW.exists()}")
print(f"Validacao oficial:         {len(val_ids)} casos | existe: {VAL_RAW.exists()}")
print("Exemplos treino:", train_ids[:2])
print("Exemplos val:   ", val_ids[:2])

Treino (With-GroundTruth): 1351 casos | existe: True
Validacao oficial:         451 casos | existe: True
Exemplos treino: ['BraTS-GoAT-00000', 'BraTS-GoAT-00003']
Exemplos val:    ['BraTS-GoAT-02489', 'BraTS-GoAT-02490']


In [4]:
MODS = ["t1n", "t1c", "t2w", "t2f"]
FILE_ENDING = ".nii.gz"

def case_dir(split_name: str, case_id: str) -> Path:
    if split_name == "train":
        return TRAIN_RAW / case_id
    elif split_name == "val":
        return VAL_RAW / case_id
    return None

def find_file(folder: Path, key: str) -> Path:
    for cand in [folder / f"{key}.nii.gz", folder / f"{key}.nii"]:
        if cand.exists():
            return cand
    cands = sorted(list(folder.glob(f"*{key}*.nii*")))
    if key == "t1n":
        cands = [c for c in cands if "t1c" not in c.name.lower()]
    if not cands:
        raise FileNotFoundError(f"{key} not found in {folder}")
    return cands[0]

def save_as_niigz(src_path: Path, dst_path: Path):
    if src_path.name.lower().endswith(".nii.gz"):
        shutil.copy2(src_path, dst_path)
        return
    img = nib.load(str(src_path))
    nib.save(img, str(dst_path))

def save_label_remap_niigz(seg_path: Path, dst_path: Path):
    img = nib.load(str(seg_path))
    data = np.asanyarray(img.dataobj).astype(np.int16)
    out = nib.Nifti1Image(data, img.affine, img.header)
    nib.save(out, str(dst_path))

for cid in train_ids[:3]:
    d = case_dir("train", cid)
    _ = [find_file(d, m) for m in MODS]
    _ = find_file(d, "seg")
print("OK")

OK


In [5]:
def export_case_to_nnunet(split_name: str, case_id: str, to_images: Path, to_labels: Path | None):
    d = case_dir(split_name, case_id)
    for ch, mod in enumerate(MODS):
        src = find_file(d, mod)
        dst = to_images / f"{case_id}_{ch:04d}{FILE_ENDING}"
        save_as_niigz(src, dst)
    if to_labels is not None:
        seg = find_file(d, "seg")
        dst = to_labels / f"{case_id}{FILE_ENDING}"
        save_label_remap_niigz(seg, dst)

for cid in tqdm(train_ids, desc="Export treino -> imagesTr/labelsTr"):
    export_case_to_nnunet("train", cid, imagesTr, labelsTr)

for cid in tqdm(val_ids, desc="Export val oficial -> imagesVs"):
    export_case_to_nnunet("val", cid, imagesVs, None)

print(f"Total imagesTr: {len(list(imagesTr.glob(f'*{FILE_ENDING}')))} | labels: {len(list(labelsTr.glob(f'*{FILE_ENDING}')))}")
print(f"Total imagesVs: {len(list(imagesVs.glob(f'*{FILE_ENDING}')))}")

Export treino -> imagesTr/labelsTr:   0%|          | 0/1351 [00:00<?, ?it/s]

Export treino -> imagesTr/labelsTr:   0%|          | 1/1351 [00:00<04:09,  5.42it/s]

Export treino -> imagesTr/labelsTr:   0%|          | 2/1351 [00:00<03:55,  5.73it/s]

Export treino -> imagesTr/labelsTr:   0%|          | 3/1351 [00:00<03:47,  5.94it/s]

Export treino -> imagesTr/labelsTr:   0%|          | 4/1351 [00:00<03:41,  6.09it/s]

...

Export val oficial -> imagesVs:  97%|█████████▋| 439/451 [00:08<00:00, 48.44it/s]

Export val oficial -> imagesVs:  98%|█████████▊| 444/451 [00:09<00:00, 45.60it/s]

Export val oficial -> imagesVs: 100%|█████████▉| 449/451 [00:09<00:00, 43.35it/s]

Export val oficial -> imagesVs: 100%|██████████| 451/451 [00:09<00:00, 48.78it/s]

Total imagesTr: 5404 | labels: 1351
Total imagesVs: 1804


In [6]:
# dataset.json - region-based (sigmoid WT/TC/ET)
dataset_json = {
    "channel_names": {"0": "T1n", "1": "T1c", "2": "T2w", "3": "T2f"},
    "labels": {
        "background":      0,
        "whole_tumor":     [1, 2, 3],
        "tumor_core":      [1, 3],
        "enhancing_tumor": [3],
    },
    "regions_class_order": [2, 1, 3],
    "numTraining": len(list(labelsTr.glob(f"*{FILE_ENDING}"))),
    "file_ending": FILE_ENDING,
}
with open(DATASET_FOLDER / "dataset.json", "w", encoding="utf-8") as f:
    json.dump(dataset_json, f, indent=2, ensure_ascii=False)
DATASET_FOLDER / "dataset.json"

PosixPath('/home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_raw/Dataset999_BraTS-GoAT-modified-sub/dataset.json')

In [7]:
!nnUNetv2_plan_and_preprocess -d {DATASET_ID} --verify_dataset_integrity -pl {PLANNER} -c {CONFIG} -np 4

Fingerprint extraction...
Dataset999_BraTS-GoAT-modified-sub


Using <class 'nnunetv2.imageio.simpleitk_reader_writer.SimpleITKIO'> as reader/writer



####################
verify_dataset_integrity Done. 
If you didn't see any error messages then your dataset is most likely OK!
####################



Using <class 'nnunetv2.imageio.simpleitk_reader_writer.SimpleITKIO'> as reader/writer


  0%|                                                  | 0/1351 [00:00<?, ?it/s]

...

100%|██████████████████████████████████████▉| 1347/1351 [22:03<00:04,  1.10s/it]

100%|██████████████████████████████████████▉| 1349/1351 [22:05<00:01,  1.09it/s]

100%|██████████████████████████████████████▉| 1350/1351 [22:06<00:00,  1.09it/s]

100%|███████████████████████████████████████| 1351/1351 [22:07<00:00,  1.15s/it]

100%|███████████████████████████████████████| 1351/1351 [22:07<00:00,  1.02it/s]


In [8]:
preprocessed_dataset = NNUNET_PREP / f"Dataset{DATASET_ID:03d}_{DATASET_NAME}"
preprocessed_dataset.exists()

True

In [9]:
prep = Path(os.environ["nnUNet_preprocessed"]) / f"Dataset{DATASET_ID:03d}_{DATASET_NAME}"
print("Preprocessed dir:", prep)
plans_files = list(prep.glob(f"{PLANS_NAME}*.json"))
print("Plans files:", plans_files)
if plans_files:
    with open(plans_files[0], "r", encoding="utf-8") as f:
        plans_json = json.load(f)
    print("Top keys:", plans_json.keys())

Preprocessed dir: /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_preprocessed/Dataset999_BraTS-GoAT-modified-sub
Plans files: [PosixPath('/home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_preprocessed/Dataset999_BraTS-GoAT-modified-sub/nnUNetResEncUNetLPlans.json')]
Top keys: dict_keys(['dataset_name', 'plans_name', 'original_median_spacing_after_transp', 'original_median_shape_after_transp', 'image_reader_writer', 'transpose_forward', 'transpose_backward', 'configurations', 'experiment_planner_used', 'label_manager', 'foreground_intensity_properties_per_channel'])


In [10]:
# Sobrescreve patch_size e batch_size (patch 128, batch 5), talvez aumentar isso para testar depois
plans_path = preprocessed_dataset / f"{PLANS_NAME}.json"
with open(plans_path, "r", encoding="utf-8") as f:
    plans_mod = json.load(f)
cfg = plans_mod["configurations"][CONFIG]
_orig_patch = list(cfg["patch_size"]); _orig_batch = int(cfg["batch_size"])
cfg["patch_size"] = [PATCH_SIZE, PATCH_SIZE, PATCH_SIZE]
cfg["batch_size"] = int(BATCH_SIZE)
with open(plans_path, "w", encoding="utf-8") as f:
    json.dump(plans_mod, f, indent=2, ensure_ascii=False)
print(f"patch: {_orig_patch} -> {cfg['patch_size']} | batch: {_orig_batch} -> {cfg['batch_size']}")

patch: [160, 192, 160] -> [128, 128, 128] | batch: 3 -> 5


In [11]:
# Trainer customizado: nnUNetTrainer_250epochs_Modified

_MODIFIED_TRAINER_SRC = r"""
import torch
import torch.nn as nn
import torch.nn.functional as F
import numpy as np
from scipy.ndimage import distance_transform_edt

from nnunetv2.training.nnUNetTrainer.variants.training_length.nnUNetTrainer_Xepochs import nnUNetTrainer_250epochs

# 1. GROUPNORM

class GroupNormWrapper(nn.GroupNorm):
    def __init__(self, num_features, eps=1e-5, affine=True, **kwargs):
        if num_features >= 8:
            num_groups = 8
        else:
            num_groups = max(1, num_features // 2)
        super().__init__(num_groups=num_groups, num_channels=num_features,
                         eps=eps, affine=affine)


def replace_norms_with_groupnorm(module):
    count = 0
    for name, child in module.named_children():
        if isinstance(child, (
            nn.InstanceNorm1d, nn.InstanceNorm2d, nn.InstanceNorm3d,
            nn.BatchNorm1d,    nn.BatchNorm2d,    nn.BatchNorm3d,
        )):
            num_features = child.num_features
            setattr(module, name, GroupNormWrapper(num_features))
            count += 1
        else:
            count += replace_norms_with_groupnorm(child)
    return count


# 3. AXIAL ATTENTION 3D (no decoder)

class AxialAttention3D(nn.Module):
    def __init__(self, channels, num_heads=4):
        super().__init__()
        while channels % num_heads != 0 and num_heads > 1:
            num_heads -= 1
        self.attn_d = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.attn_h = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.attn_w = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.norm = GroupNormWrapper(channels)

    def forward(self, x):
        B, C, D, H, W = x.shape
        xd = x.permute(0, 3, 4, 2, 1).contiguous().view(B*H*W, D, C)
        xd, _ = self.attn_d(xd, xd, xd)
        xd = xd.view(B, H, W, D, C).permute(0, 4, 3, 1, 2).contiguous()
        xh = x.permute(0, 2, 4, 3, 1).contiguous().view(B*D*W, H, C)
        xh, _ = self.attn_h(xh, xh, xh)
        xh = xh.view(B, D, W, H, C).permute(0, 4, 1, 3, 2).contiguous()
        xw = x.permute(0, 2, 3, 4, 1).contiguous().view(B*D*H, W, C)
        xw, _ = self.attn_w(xw, xw, xw)
        xw = xw.view(B, D, H, W, C).permute(0, 4, 1, 2, 3).contiguous()
        return self.norm(x + xd + xh + xw)


class StageWithAttention(nn.Module):
    def __init__(self, stage, attn):
        super().__init__()
        self.stage = stage
        self.attn = attn

    def forward(self, x):
        out = self.stage(x)
        if out.dim() == 5:
            return self.attn(out)
        return out


def inject_axial_attention_in_decoder(model):
    if not hasattr(model, "decoder") or not hasattr(model.decoder, "stages"):
        return False
    if len(model.decoder.stages) == 0:
        return False
    target_idx = 0  # primeiro stage do decoder = menor resolucao (logo apos o bottleneck)
    dec_stage = model.decoder.stages[target_idx]
    out_channels = None
    for m in dec_stage.modules():
        if isinstance(m, nn.Conv3d):
            out_channels = m.out_channels
    if out_channels is None:
        return False
    attn = AxialAttention3D(out_channels, num_heads=4)
    model.decoder.stages[target_idx] = StageWithAttention(dec_stage, attn)
    return True


# 4. HD LOSS

class HausdorffDTLoss(nn.Module):
    def __init__(self, alpha=2.0):
        super().__init__()
        self.alpha = alpha

    @staticmethod
    @torch.no_grad()
    def _dt_batch(mask):
        np_mask = (mask.detach().cpu().numpy() > 0.5).astype(bool)
        out = np.zeros(np_mask.shape, dtype=np.float32)
        if np_mask.ndim == 5:
            for b in range(np_mask.shape[0]):
                for c in range(np_mask.shape[1]):
                    fg = np_mask[b, c]
                    if fg.any() and not fg.all():
                        out[b, c] = distance_transform_edt(~fg)
        return torch.from_numpy(out).to(mask.device)

    def forward(self, pred_prob, target_bin):
        if target_bin.dtype != torch.float32:
            target_bin = target_bin.float()
        dt_gt = self._dt_batch(target_bin)
        dt_pr = self._dt_batch(pred_prob)
        err = (pred_prob - target_bin) ** 2
        weight = dt_gt.pow(self.alpha) + dt_pr.pow(self.alpha)
        return (err * weight).mean()


class DC_BCE_HD_Loss(nn.Module):
    def __init__(self, base_loss, hd_lambda=0.05, hd_warmup_epochs=10,
                 hd_every_n_steps=5):
        super().__init__()
        self.base_loss = base_loss
        self.hd_loss = HausdorffDTLoss(alpha=2.0)
        self.hd_lambda = hd_lambda
        self.hd_warmup_epochs = hd_warmup_epochs
        self.hd_every_n_steps = hd_every_n_steps
        self.current_epoch = 0
        self._step = 0

    def set_epoch(self, e):
        self.current_epoch = e

    def forward(self, logits, target):
        base = self.base_loss(logits, target)
        self._step += 1
        if self.current_epoch < self.hd_warmup_epochs:
            return base
        if self._step % self.hd_every_n_steps != 0:
            return base
        if isinstance(logits, list):
            logits_full = logits[0]
            target_full = target[0] if isinstance(target, list) else target
        else:
            logits_full = logits
            target_full = target
        pred_prob = torch.sigmoid(logits_full)
        hd = self.hd_loss(pred_prob, target_full)
        return base + self.hd_lambda * hd


# Trainer

class nnUNetTrainer_250epochs_Modified(nnUNetTrainer_250epochs):

    @staticmethod
    def build_network_architecture(*args, **kwargs):
        network = nnUNetTrainer_250epochs.build_network_architecture(*args, **kwargs)
        n = replace_norms_with_groupnorm(network)
        injected = inject_axial_attention_in_decoder(network)
        print(f"[Modified] build_network_architecture: GroupNorm={n} | AxialAttn_decoder={injected}")
        return network

    def _build_loss(self):
        base_loss = super()._build_loss()
        compound = DC_BCE_HD_Loss(base_loss, hd_lambda=0.05,
                                  hd_warmup_epochs=10, hd_every_n_steps=5)
        if self.local_rank == 0:
            print("[Modified] Loss: DC+BCE region-based + 0.05*HD (warmup=10, every=5 steps)")
        return compound

    def on_train_epoch_start(self):
        super().on_train_epoch_start()
        if hasattr(self.loss, "set_epoch"):
            self.loss.set_epoch(self.current_epoch)
"""

_nnunet_pkg_dir = Path(_nnunetv2_pkg.__file__).parent
_trainer_variants_dir = _nnunet_pkg_dir / "training" / "nnUNetTrainer" / "variants"
_trainer_file = _trainer_variants_dir / "nnUNetTrainer_250epochs_Modified.py"
_trainer_file.write_text(_MODIFIED_TRAINER_SRC, encoding="utf-8")

import importlib
_mod_name = "nnunetv2.training.nnUNetTrainer.variants.nnUNetTrainer_250epochs_Modified"
if _mod_name in importlib.sys.modules:
    importlib.reload(importlib.sys.modules[_mod_name])
_mod = importlib.import_module(_mod_name)
assert hasattr(_mod, "nnUNetTrainer_250epochs_Modified"), "Trainer nao registrado."

print(f"Trainer salvo em: {_trainer_file}")
print(f"Trainer registrado: {TRAINER}")
print("  1. GroupNorm (substitui InstanceNorm) -- via build_network_architecture")
print("  2. AxialAttention3D no decoder        -- via build_network_architecture")
print("  3. HD loss (warmup + subsampling)     -- via _build_loss")
print("  4. Encoder grande: planner ResEncL")

Trainer salvo em: /home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/site-packages/nnunetv2/training/nnUNetTrainer/variants/nnUNetTrainer_250epochs_Modified.py
Trainer registrado: nnUNetTrainer_250epochs_Modified
  1. GroupNorm (substitui InstanceNorm) -- via build_network_architecture
  2. AxialAttention3D no decoder        -- via build_network_architecture
  3. HD loss (warmup + subsampling)     -- via _build_loss
  4. Encoder grande: planner ResEncL


In [12]:
# Treina os 5 folds (nnU-Net gera os splits 5-fold automaticamente).
# --npz: salva os softmax da validacao (necessario para nnUNetv2_find_best_configuration / postprocessing).
for f in FOLDS:
    print(f"\n===== Treinando fold {f} =====")
    get_ipython().system(f"nnUNetv2_train {DATASET_ID} {CONFIG} {f} -device cuda -p {PLANS_NAME} -tr {TRAINER} --npz")


===== Treinando fold 0 =====


Using device: cuda:0



#######################################################################
Please cite the following paper when using nnU-Net:
Isensee, F., Jaeger, P. F., Kohl, S. A., Petersen, J., & Maier-Hein, K. H. (2021). nnU-Net: a self-configuring method for deep learning-based biomedical image segmentation. Nature methods, 18(2), 203-211.
#######################################################################



[Modified] build_network_architecture: GroupNorm=124 | AxialAttn_decoder=True


2026-06-10 17:02:38.009634: Using torch.compile...


...

2026-06-16 11:59:12.118335: predicting BraTS-GoAT-02454


2026-06-16 11:59:12.196834: BraTS-GoAT-02454, shape torch.Size([4, 141, 184, 140]), rank 0


2026-06-16 11:59:12.935323: predicting BraTS-GoAT-02460


2026-06-16 11:59:13.009282: BraTS-GoAT-02460, shape torch.Size([4, 142, 172, 133]), rank 0


2026-06-16 11:59:28.484254: Validation complete
2026-06-16 11:59:28.484378: Mean Validation Dice:  0.9031887745403241


In [13]:
# Postprocessing nnU-Net: determina nos 5 folds (OOF) e so aplica se melhorar.
!nnUNetv2_find_best_configuration {DATASET_ID} -c {CONFIG} -p {PLANS_NAME} -tr {TRAINER}


***All results:***
nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres: 0.8977528537373397

*Best*: nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres: 0.8977528537373397

***Determining postprocessing for best model/ensemble***


Removing all but the largest foreground region did not improve results!


Removing all but the largest component for (1, 2, 3) did not improve results! Dice before: 0.92278 after: 0.91577


Removing all but the largest component for (1, 3) did not improve results! Dice before: 0.90965 after: 0.89647


Removing all but the largest component for (3,) did not improve results! Dice before: 0.86083 after: 0.84518



***Run inference like this:***

nnUNetv2_predict -d Dataset999_BraTS-GoAT-modified-sub -i INPUT_FOLDER -o OUTPUT_FOLDER -f  0 1 2 3 4 -tr nnUNetTrainer_250epochs_Modified -c 3d_fullres -p nnUNetResEncUNetLPlans

***Once inference is completed, run postprocessing like this:***

nnUNetv2_apply_postprocessing -i OUTPUT_FOLDER -o OUTPUT_FOLDER_PP -pp_pkl_file /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_results/Dataset999_BraTS-GoAT-modified-sub/nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres/crossval_results_folds_0_1_2_3_4/postprocessing.pkl -np 8 -plans_json /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_results/Dataset999_BraTS-GoAT-modified-sub/nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres/crossval_results_folds_0_1_2_3_4/plans.json


In [14]:
# Inferencia ENSEMBLE (5 folds, TTA ligado) nas DUAS versoes de checkpoint + postprocessing oficial.
model_dir = NNUNET_RES / f"Dataset{DATASET_ID:03d}_{DATASET_NAME}" / f"{TRAINER}__{PLANS_NAME}__{CONFIG}"
pp_pkls = list(model_dir.glob("crossval_results*/postprocessing.pkl"))
plans_json_path = model_dir / "plans.json"
dataset_json_path = model_dir / "dataset.json"
pp = pp_pkls[0] if pp_pkls else None
print("postprocessing.pkl:", pp)
# aviso Falha: sem o .pkl o postproc nao roda e submeteriamos 'raw' por engano.
assert pp is not None, ("postprocessing.pkl nao encontrado em crossval_results*/ - "
                        "rode nnUNetv2_find_best_configuration (requer treino com --npz).")

runs = [("checkpoint_final.pth", PRED_LAST, "last"),
        ("checkpoint_best.pth",  PRED_BEST, "best")]

for chk, root, tag in runs:
    raw = root / "ofc_validation_raw"
    final = root / "ofc_validation"
    print(f"\n===== Inferencia ensemble [{tag}] ({chk}) -> {root.name} =====")
    get_ipython().system(
        f'nnUNetv2_predict -i "{imagesVs}" -o "{raw}" -d {DATASET_ID} -c {CONFIG} '
        f'-f 0 1 2 3 4 -p {PLANS_NAME} -tr {TRAINER} -chk {chk}')
    n_raw = len(list(raw.glob(f"*{FILE_ENDING}")))
    assert n_raw > 0, f"Nenhuma predicao para {chk} - confira o treino dos 5 folds."
    get_ipython().system(
        f'nnUNetv2_apply_postprocessing -i "{raw}" -o "{final}" '
        f'-pp_pkl_file "{pp}" -np 4 -plans_json "{plans_json_path}" -dataset_json "{dataset_json_path}"')

    #Checagens finais antes do zip de submissao
    n_final = len(list(final.glob(f"*{FILE_ENDING}")))
    n_cases_in = len(list(imagesVs.glob(f"*_0000{FILE_ENDING}")))
    assert n_final == n_cases_in, (
        f"[{tag}] submissao incompleta: {n_final} mascaras != {n_cases_in} casos de entrada.")
    bad_labels = {}
    for m in sorted(final.glob(f"*{FILE_ENDING}")):
        vals = set(np.unique(np.asanyarray(nib.load(str(m)).dataobj)).astype(int).tolist())
        extra = vals - {0, 1, 2, 3}
        if extra:
            bad_labels[m.name] = sorted(extra)
    assert not bad_labels, f"[{tag}] rotulos fora de {{0,1,2,3}}: {bad_labels}"
    print(f"  SUBMETER [{tag}]: {final}  ({n_final} mascaras | casos OK | rotulos OK)")

postprocessing.pkl: /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_results/Dataset999_BraTS-GoAT-modified-sub/nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres/crossval_results_folds_0_1_2_3_4/postprocessing.pkl

===== Inferencia ensemble [last] (checkpoint_final.pth) -> nnUnet_modified_sub_last =====



#######################################################################
Please cite the following paper when using nnU-Net:
Isensee, F., Jaeger, P. F., Kohl, S. A., Petersen, J., & Maier-Hein, K. H. (2021). nnU-Net: a self-configuring method for deep learning-based biomedical image segmentation. Nature methods, 18(2), 203-211.
#######################################################################



[Modified] build_network_architecture: GroupNorm=124 | AxialAttn_decoder=True


There are 451 cases in the source folder
I am processing 0 out of 1 (max process ID is 0, we start counting with 0!)
There are 451 cases that I would like to predict



Predicting BraTS-GoAT-02489:
perform_everything_on_device: True


...

 75%|█████████████████████████████████▊           | 6/8 [00:02<00:00,  2.06it/s]

 88%|███████████████████████████████████████▍     | 7/8 [00:03<00:00,  2.05it/s]

100%|█████████████████████████████████████████████| 8/8 [00:03<00:00,  2.08it/s]


sending off prediction to background worker for resampling and export
done with BraTS-GoAT-02939


  SUBMETER [best]: /home/henrique.grande/brats_goat_experiments/predictions/nnUnet_modified_sub_best/ofc_validation  (451 mascaras | casos OK | rotulos OK)


In [15]:
# Curva de loss do fold 0
trainer_dir = NNUNET_RES / f"Dataset{DATASET_ID:03d}_{DATASET_NAME}" / f"{TRAINER}__{PLANS_NAME}__{CONFIG}" / "fold_0"
ckpt_path = trainer_dir / "checkpoint_final.pth"
if not ckpt_path.exists():
    ckpt_path = trainer_dir / "checkpoint_best.pth"
print("Lendo historico de:", ckpt_path)
ckpt = torch.load(str(ckpt_path), map_location="cpu", weights_only=False)
log = ckpt.get("logging", {})
train_losses = log.get("train_losses", [])
val_losses   = log.get("val_losses",   [])
fig, ax = plt.subplots(figsize=(10, 4))
ax.plot(train_losses, label="train")
ax.plot(val_losses,   label="val", ls="--")
ax.set_xlabel("Epoca")
ax.set_ylabel("Loss (Dice + BCE region-based, deep sup.)")
ax.set_title(f"Modified submission (fold 0) - {len(train_losses)} epocas")
ax.legend()
ax.grid(True, alpha=0.3)
plt.tight_layout()
plt.savefig(trainer_dir / "loss_curves.png", dpi=150)
plt.show()

Lendo historico de: /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_results/Dataset999_BraTS-GoAT-modified-sub/nnUNetTrainer_250epochs_Modified__nnUNetResEncUNetLPlans__3d_fullres/fold_0/checkpoint_final.pth
